# Learned Stage-Wise Curvature Tuning on OCTMNIST

This notebook evaluates Learned Stage-Wise Curvature Tuning (SW-CT) on the OCTMNIST dataset using an ImageNet-pretrained ResNet-50.

OCTMNIST is a medical image-classification dataset containing retinal optical coherence tomography images. Its visual domain differs substantially from the natural images used during ImageNet pretraining, providing a strong domain-shift setting for evaluating Learned SW-CT.

The experiments compare four conditions:

1. **Baseline** — the original pretrained ResNet with ReLU activations and a trained downstream classifier.
2. **Single-Parameter Curvature Tuning (S-CT)** — one global beta selected through validation-based exhaustive search.
3. **Learned SW-CT with fixed initialization** — four trainable stage-wise beta parameters initialized at 0.78.
4. **Learned SW-CT with random initialization** — four trainable stage-wise beta parameters independently initialized between 0.70 and 0.99.

Each condition is evaluated using seeds 42, 43, and 44.

Experiments are conducted for both 20 and 30 epochs to determine whether additional optimization improves performance or changes the learned stage-wise beta values.

Wall-clock execution time is also recorded to compare computational cost across Baseline, S-CT, and Learned SW-CT.

In [1]:
!nvidia-smi

Mon Oct  5 17:40:56 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 580.178.04             Driver Version: 580.178.04     CUDA Version: 13.0     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  Tesla T4                       Off |   00000000:00:04.0 Off |                    0 |
| N/A   49C    P8             11W /   70W |       0MiB /  15360MiB |      0%      Default |
|                                         |                        |                  N/A |
+-----------------------------------------+-----

In [1]:
%cd /content

!git clone -b main \
    https://github.com/NiftySnek173/research-curvature-tuning.git

%cd /content/research-curvature-tuning/src/curvature-tuning

!git branch --show-current
!git log -1 --oneline

/content
Cloning into 'curvature-tuning-research'...
remote: Enumerating objects: 631, done.
remote: Counting objects: 100% (303/303), done.
remote: Compressing objects: 100% (151/151), done.
remote: Total 631 (delta 191), reused 223 (delta 131), pack-reused 328 (from 1)
Receiving objects: 100% (631/631), 22.92 MiB | 9.14 MiB/s, done.
Resolving deltas: 100% (322/322), done.
/content/curvature-tuning-research/src/curvature-tuning
stage-wise-ct
27ee9f0 (HEAD -> stage-wise-ct, origin/stage-wise-ct, origin/HEAD) updated food 101 execution


## Environment Setup

The repository dependencies are installed before running the experiments.

After installation, the Colab runtime should be restarted so that the required package versions are loaded correctly.

In [2]:
%pip install -q -r requirements.txt
%pip install --force-reinstall --no-cache-dir "numpy==1.26.3"

  Preparing metadata (setup.py) ... done
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 15.7/15.7 MB 79.2 MB/s eta 0:00:0000:0100:01
  Installing build dependencies ... done
  Getting requirements to build wheel ... done
  Installing backend dependencies ... done
  Preparing metadata (pyproject.toml) ... done
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 42.4/42.4 kB 2.2 MB/s eta 0:00:00
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 57.6/57.6 kB 2.9 MB/s eta 0:00:00
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 89.9/89.9 kB 5.3 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 64.9/64.9 kB 3.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 133.2/133.2 kB 8.8 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 2.3/2.3 MB 69.7 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 78.4/78.4 kB 4.7 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 12.7/12.7 MB 106.1 MB/s eta 0:00:0000:010:01
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 8.3/

In [2]:
%cd /content/research-curvature-tuning/src/curvature-tuning

import os
import torch

os.environ["WANDB_MODE"] = "disabled"

print("Working directory:", os.getcwd())
print("PyTorch:", torch.__version__)
print("CUDA available:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))

/content/curvature-tuning-research/src/curvature-tuning
Working directory: /content/curvature-tuning-research/src/curvature-tuning
PyTorch: 2.6.0+cu124
CUDA available: True
GPU: NVIDIA L4


## Arabic Digits Dataset

Before running the experiments, the Arabic Digits data loaders are checked to confirm that the downstream dataset can be loaded correctly.

The same dataset split and random seed protocol are used for Baseline, S-CT, and Learned SW-CT so that the methods are compared under the same conditions.

In [4]:
import aiohttp
from datasets import load_dataset, DownloadConfig

download_config = DownloadConfig(
    max_retries=5,
    storage_options={
        "client_kwargs": {
            "timeout": aiohttp.ClientTimeout(
                total=7200,
                connect=120,
                sock_read=600,
            )
        }
    },
)

octmnist_cached = load_dataset(
    "randall-lab/medmnist",
    name="octmnist",
    trust_remote_code=True,
    download_config=download_config,
)

print("OCTMNIST downloaded and prepared.")
print(octmnist_cached)

OCTMNIST downloaded and prepared.
DatasetDict({
    train: Dataset({
        features: ['image', 'label'],
        num_rows: 97477
    })
    test: Dataset({
        features: ['image', 'label'],
        num_rows: 1000
    })
    validation: Dataset({
        features: ['image', 'label'],
        num_rows: 10832
    })
})


In [5]:
from utils.data import get_data_loaders

train_loader, test_loader, val_loader = get_data_loaders(
    "imagenet_to_medmnist/octmnist",
    train_batch_size=32,
    test_batch_size=128,
    seed=42,
)

print("Train samples:", len(train_loader.dataset))
print("Validation samples:", len(val_loader.dataset))
print("Test samples:", len(test_loader.dataset))

images, labels = next(iter(train_loader))

print("Image batch shape:", images.shape)
print("Label batch shape:", labels.shape)
print("Labels:", labels[:10])

Train samples: 97477
Validation samples: 10832
Test samples: 1000
Image batch shape: torch.Size([32, 3, 224, 224])
Label batch shape: torch.Size([32])
Labels: tensor([0, 0, 0, 3, 0, 0, 3, 0, 2, 0])


# ResNet-50 Experiments

ResNet-50 is evaluated first because it was used during the initial development of Learned SW-CT.

The experiment compares Baseline, S-CT, fixed-initialization SW-CT, and random-initialization SW-CT.

All methods use the same ImageNet-pretrained backbone, Arabic Digits dataset split, experimental seeds, and downstream training protocol.

## ResNet-50 — 20-Epoch Evaluation

The first evaluation uses 20 training epochs.

This provides the primary reference experiment and maintains compatibility with the earlier Learned SW-CT work.

### Methods

**Baseline**

The pretrained ResNet-50 retains its original ReLU activations. The backbone is frozen and only the downstream classifier is trained.

**S-CT**

The original Single-Parameter Curvature Tuning method searches over a single beta shared throughout the network. Candidate beta values from 0.70 to 1.00 are evaluated using validation performance, and the best candidate is evaluated on the test set.

The recorded S-CT execution time includes the complete beta search rather than only the final selected beta.

**Learned SW-CT — Fixed Initialization**

Four trainable beta parameters are assigned to the four ResNet stages. All four begin at beta = 0.78.

This preserves the initialization used in the original Learned SW-CT experiments.

**Learned SW-CT — Random Initialization**

Four trainable stage-wise beta parameters are initialized independently between 0.70 and 0.99.

The random initialization is generated deterministically from the experiment seed. This allows the experiment to test whether Learned SW-CT depends on the fixed 0.78 starting value while remaining reproducible.

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-06 03:22:47.111 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet50_seed42_epochs20.log
2026-10-06 03:22:47.116 | INFO     | __main__:main:78 - Running on cuda
2026-10-06 03:22:49.703 | INFO     | __main__:main:105 - Testing baseline...
2026-10-06 03:22:49.777 | INFO     | __main__:main:116 - Number of trainable parameters: 8196
2026-10-06 03:22:49.778 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-06 03:28:37.964 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.411439, Accuracy: 31.25%
2026-10-06 03:28:38.249 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.276519, Accuracy: 43.53%
2026-10-06 03:28:38.559 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.181148, Accuracy: 52.35%
2026-10-06 03:28:38.886 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.115833, Accuracy: 58.18%
2026-10-06 03:28:39.171 | INFO     | train:train_epoch:47 - Epoch 1, Step 

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-06 12:29:14.428 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet50_seed43_epochs20.log
2026-10-06 12:29:14.432 | INFO     | __main__:main:78 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 197MB/s]
2026-10-06 12:29:18.219 | INFO     | __main__:main:105 - Testing baseline...
2026-10-06 12:29:18.420 | INFO     | __main__:main:116 - Number of trainable parameters: 8196
2026-10-06 12:29:18.420 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-06 12:35:02.281 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.277153, Accuracy: 53.12%
2026-10-06 12:35:02.615 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.253835, Accuracy: 46.16%
2026-10-06 12:35:02.962 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss:

In [ ]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-07 02:49:25.142 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet50_seed44_epochs20.log
2026-10-07 02:49:25.148 | INFO     | __main__:main:78 - Running on cuda
2026-10-07 02:49:28.486 | INFO     | __main__:main:105 - Testing baseline...
2026-10-07 02:49:28.532 | INFO     | __main__:main:116 - Number of trainable parameters: 8196
2026-10-07 02:49:28.533 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-07 02:54:44.146 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.576732, Accuracy: 6.25%
2026-10-07 02:54:44.399 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.382947, Accuracy: 30.41%
2026-10-07 02:54:44.635 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.243718, Accuracy: 45.21%
2026-10-07 02:54:44.860 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.154519, Accuracy: 53.44%
2026-10-07 02:54:45.083 | INFO     | train:train_epoch:47 - Epoch 1, Step 4

### Learned SW-CT with Fixed Beta Initialization

The original Learned SW-CT configuration is first reproduced using the fixed initialization:

\[[\beta_1,\beta_2,\beta_3,\beta_4]=[0.78,0.78,0.78,0.78].\]

The initial value is only a starting point. During training, the four beta parameters are optimized independently together with the downstream classifier.

These runs provide the reference against which random initialization will be compared.

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-10 12:21:32.233 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed42_epochs20_initfixed0.78_betalr0.01.log
2026-10-10 12:21:32.340 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 177MB/s]
2026-10-10 12:21:36.685 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-10 12:21:36.686 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-10 12:21:36.819 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-10 12:21:36.820 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-10 12:21:36.820 | INFO  

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-11 09:54:07.840 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed43_epochs20_initfixed0.78_betalr0.01.log
2026-10-11 09:54:07.904 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 223MB/s]
2026-10-11 09:54:09.864 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-11 09:54:09.864 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 09:54:09.955 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-11 09:54:09.956 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 09:54:09.957 | INFO  

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-11 20:19:12.981 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed44_epochs20_initfixed0.78_betalr0.01.log
2026-10-11 20:19:13.045 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 240MB/s]
2026-10-11 20:19:19.525 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-11 20:19:19.526 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 20:19:19.609 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-11 20:19:19.610 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 20:19:19.610 | INFO  

### Learned SW-CT with Random Beta Initialization

The fixed beta = 0.78 initialization may raise the question of whether Learned SW-CT performs well only because its starting point was informed by the earlier S-CT experiments.

To test this dependency, each of the four stage-wise beta parameters is now initialized independently from a uniform distribution between 0.70 and 0.99.

The initialization is reproducible: the random generator is seeded using the experiment seed. Therefore, each seed always receives the same initial beta vector.

If random initialization produces similar performance to the fixed 0.78 experiment, this provides evidence that the Learned SW-CT result is not dependent on a single hand-selected initialization.

In [20]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-14 16:04:53.652 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed42_epochs20_initrandom_betalr0.01.log
2026-10-14 16:04:53.705 | INFO     | __main__:main:302 - Running on cuda
2026-10-14 16:04:55.618 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-14 16:04:55.618 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-14 16:04:55.697 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-14 16:04:55.698 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-14 16:04:55.698 | INFO     | __main__:main:439 - Total trainable parameters: 8200
2026-10-14 16:04:57.391 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.377932, Accuracy: 21.88%
2026-10-14 16:05:35.806 | INFO    

In [21]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-14 22:54:25.549 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed43_epochs20_initrandom_betalr0.01.log
2026-10-14 22:54:25.601 | INFO     | __main__:main:302 - Running on cuda
2026-10-14 22:54:27.443 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-14 22:54:27.444 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-14 22:54:27.506 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-14 22:54:27.507 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-14 22:54:27.507 | INFO     | __main__:main:439 - Total trainable parameters: 8200
2026-10-14 22:54:28.633 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.387454, Accuracy: 21.88%
2026-10-14 22:55:07.263 | INFO  

In [22]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-15 05:43:56.835 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed44_epochs20_initrandom_betalr0.01.log
2026-10-15 05:43:56.888 | INFO     | __main__:main:302 - Running on cuda
2026-10-15 05:43:58.815 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-15 05:43:58.815 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-15 05:43:58.879 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-15 05:43:58.880 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-15 05:43:58.880 | INFO     | __main__:main:439 - Total trainable parameters: 8200
2026-10-15 05:44:00.000 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.215194, Accuracy: 56.25%
2026-10-15 05:44:38.666 | INFO  

# ResNet-50 — 30-Epoch Evaluation

The same experiments are now repeated for 30 epochs.

The purpose of increasing the training budget is to determine whether the 20-epoch results are limited by insufficient optimization.

If a method improves substantially with 30 epochs, this suggests that additional optimization is useful. If performance remains similar, it indicates that the method has largely stabilized within the original 20-epoch training budget.

All other experimental settings remain unchanged.

For random-initialization SW-CT, the same seed produces exactly the same initial four-beta vector in both the 20-epoch and 30-epoch experiments. Therefore, initialization is held constant while the training duration changes.

Execution time is again recorded to measure the computational cost of extending training from 20 to 30 epochs.

In [23]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-15 12:33:37.832 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet50_seed42_epochs30.log
2026-10-15 12:33:37.833 | INFO     | __main__:main:78 - Running on cuda
2026-10-15 12:33:39.625 | INFO     | __main__:main:105 - Testing baseline...
2026-10-15 12:33:39.670 | INFO     | __main__:main:116 - Number of trainable parameters: 8196
2026-10-15 12:33:39.670 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-15 12:36:35.435 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.411386, Accuracy: 31.25%
2026-10-15 12:36:35.659 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.276509, Accuracy: 43.53%
2026-10-15 12:36:35.885 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.181137, Accuracy: 52.36%
2026-10-15 12:36:36.102 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.115830, Accuracy: 58.19%
2026-10-15 12:36:36.328 | INFO     | train:train_epoch:47 - Epoch 1, Step 

In [24]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-15 18:24:45.229 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet50_seed43_epochs30.log
2026-10-15 18:24:45.231 | INFO     | __main__:main:78 - Running on cuda
2026-10-15 18:24:47.114 | INFO     | __main__:main:105 - Testing baseline...
2026-10-15 18:24:47.158 | INFO     | __main__:main:116 - Number of trainable parameters: 8196
2026-10-15 18:24:47.158 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-15 18:27:42.740 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.277091, Accuracy: 53.12%
2026-10-15 18:27:42.975 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.253856, Accuracy: 46.19%
2026-10-15 18:27:43.205 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.169065, Accuracy: 55.18%
2026-10-15 18:27:43.438 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.099545, Accuracy: 60.37%
2026-10-15 18:27:43.675 | INFO     | train:train_epoch:47 - Epoch 1, Step 

In [17]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-16 01:43:12.505 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-octmnist_resnet50_seed44_epochs30.log
2026-10-16 01:43:12.506 | INFO     | __main__:main:78 - Running on cuda
2026-10-16 01:43:14.529 | INFO     | __main__:main:105 - Testing baseline...
2026-10-16 01:43:14.574 | INFO     | __main__:main:116 - Number of trainable parameters: 8196
2026-10-16 01:43:14.574 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-16 01:46:10.160 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.576782, Accuracy: 6.25%
2026-10-16 01:46:10.383 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 1.382944, Accuracy: 30.41%
2026-10-16 01:46:10.597 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.243712, Accuracy: 45.21%
2026-10-16 01:46:10.820 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.154514, Accuracy: 53.44%
2026-10-16 01:46:11.043 | INFO     | train:train_epoch:47 - Epoch 1, Step 4

In [18]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-16 07:34:36.177 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed42_epochs30_initfixed0.78_betalr0.01.log
2026-10-16 07:34:36.230 | INFO     | __main__:main:302 - Running on cuda
2026-10-16 07:34:38.188 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-16 07:34:38.189 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-16 07:34:38.252 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-16 07:34:38.252 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-16 07:34:38.253 | INFO     | __main__:main:439 - Total trainable parameters: 8200
2026-10-16 07:34:39.386 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.401936, Accuracy: 21.88%
2026-10-16 07:35:18.092 | INFO     | train:tra

In [5]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-16 19:27:03.334 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed43_epochs30_initfixed0.78_betalr0.01.log
2026-10-16 19:27:03.393 | INFO     | __main__:main:302 - Running on cuda
2026-10-16 19:27:06.318 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-16 19:27:06.318 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-16 19:27:06.395 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-16 19:27:06.396 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-16 19:27:06.396 | INFO     | __main__:main:439 - Total trainable parameters: 8200
2026-10-16 19:27:08.138 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.397972, Accuracy: 28.12%
2026-10-16 19:27:46.655 | INFO     | train:tra

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-17 05:41:03.574 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed44_epochs30_initfixed0.78_betalr0.01.log
2026-10-17 05:41:03.626 | INFO     | __main__:main:302 - Running on cuda
2026-10-17 05:41:05.543 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-17 05:41:05.543 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-17 05:41:05.605 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-17 05:41:05.606 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-17 05:41:05.606 | INFO     | __main__:main:439 - Total trainable parameters: 8200
2026-10-17 05:41:06.710 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.230088, Accuracy: 50.00%
2026-10-17 05:41:45.355 | INFO     | train:tra

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-17 21:35:22.643 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed42_epochs30_initrandom_betalr0.01.log
2026-10-17 21:35:22.695 | INFO     | __main__:main:302 - Running on cuda
2026-10-17 21:35:24.511 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-17 21:35:24.511 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-17 21:35:24.575 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-17 21:35:24.575 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-17 21:35:24.576 | INFO     | __main__:main:439 - Total trainable parameters: 8200
2026-10-17 21:35:25.689 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.377932, Accuracy: 21.88%
2026-10-17 21:36:04.111 | INFO    

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-18 07:49:25.136 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed43_epochs30_initrandom_betalr0.01.log
2026-10-18 07:49:25.188 | INFO     | __main__:main:302 - Running on cuda
2026-10-18 07:49:26.969 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-18 07:49:26.969 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
2026-10-18 07:49:27.031 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-18 07:49:27.032 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-18 07:49:27.032 | INFO     | __main__:main:439 - Total trainable parameters: 8200
2026-10-18 07:49:28.144 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.387454, Accuracy: 21.88%
2026-10-18 07:50:06.805 | INFO     | train:train_epoch:47 - Epoch 1, Step 10

In [9]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/octmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-18 18:04:26.493 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-octmnist_resnet50_seed44_epochs30_initrandom_betalr0.01.log
2026-10-18 18:04:26.546 | INFO     | __main__:main:302 - Running on cuda
2026-10-18 18:04:28.345 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-18 18:04:28.345 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-18 18:04:28.407 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-18 18:04:28.408 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-18 18:04:28.408 | INFO     | __main__:main:439 - Total trainable parameters: 8200
2026-10-18 18:04:29.527 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 1.215194, Accuracy: 56.25%
2026-10-18 18:05:08.129 | INFO  